In [0]:
# Data Ingestion - mount container
# Step 1 - Basic information
sas_token="s*******"
container_name="*****"
storage_account_name="*******"
mount_point ="Mount_Point_fy"
# Step 2: mounting
dbutils.fs.mount(
source = "wasbs://" +container_name+"@"+storage_account_name+".blob.core.windows.net",
mount_point = "/mnt/"+mount_point,
extra_configs = {'fs.azure.sas.'+container_name+"."+storage_account_name+'.blob.core.windows.net':sas_token})
# Step 3: list files in the mount point
display(dbutils.fs.ls("/mnt/"+mount_point+"/raw"))
 
# Step 4: Data Ingestion - unmount
# it should be unmounted after cleaning data
# Since there is no code here for cleaning the data, the code for unmounting has been commented out for now
#dbutils.fs.unmount("/mnt/"+mount_point)

path,name,size,modificationTime
dbfs:/mnt/Mount_Point_fy/raw/Address.csv,Address.csv,2945120,1792408640000
dbfs:/mnt/Mount_Point_fy/raw/CountryRegion.csv,CountryRegion.csv,8596,1792408638000
dbfs:/mnt/Mount_Point_fy/raw/Customer.json,Customer.json,7986581,1792408646000
dbfs:/mnt/Mount_Point_fy/raw/Person.csv,Person.csv,1084967,1792408640000
dbfs:/mnt/Mount_Point_fy/raw/Product.csv,Product.csv,90726,1792408638000
dbfs:/mnt/Mount_Point_fy/raw/ProductUpdated.csv,ProductUpdated.csv,91064,1792408638000
dbfs:/mnt/Mount_Point_fy/raw/SalesOrderDetail.json,SalesOrderDetail.json,61729207,1792408662000
dbfs:/mnt/Mount_Point_fy/raw/SalesOrderHeader.csv,SalesOrderHeader.csv,7496262,1792408643000
dbfs:/mnt/Mount_Point_fy/raw/StateProvince.csv,StateProvince.csv,15848,1792408640000
dbfs:/mnt/Mount_Point_fy/raw/productCategory.csv,productCategory.csv,331,1792408638000


In [0]:
dbutils.fs.refreshMounts

<bound method DBUtils.FSHandler.refreshMounts of Package 'dbutils.fs'. For more information, type 'display(dbutils.fs)' in a cell.>

In [0]:
dbutils.fs.unmount("/mnt/Mount_Point_fy")

## CSV Schemas erstellen
## 
Wir erstellen ein Schema für alle CSV-Dateien. Außerdem definieren wir Importe und globale Variablen.

In [0]:
# DBTITLE 1,Step 3: Schemas
base = "/mnt/" + mount_point
from pyspark.sql import functions as F
from delta.tables import DeltaTable
from pyspark.sql import Window
from pyspark.sql.functions import col, try_to_timestamp

paths = {
    "raw": base + "/raw/",
    "standardized": base + "/standardized/",
    "processed": base + "/processed/"
}

# CSV-Schemas (String/Double bewusst, damit die Rohdaten nicht abbrechen)
csv_schemas = {
    "Person": """BusinessEntityID INT, PersonType STRING, NameStyle INT, Title STRING,
        FirstName STRING, MiddleName STRING, LastName STRING, Suffix STRING,
        EmailPromotion INT, AdditionalContactInfo STRING, ModifiedDate STRING""",

    "Address": """AddressID INT, AddressLine1 STRING, AddressLine2 STRING, City STRING,
        StateProvinceID INT, PostalCode STRING, SpatialLocation STRING,
        rowguid STRING, ModifiedDate STRING""",

    "CountryRegion": """CountryRegionCode STRING, Name STRING, ModifiedDate STRING, _c3 STRING""",

    "StateProvince": """StateProvinceID INT, StateProvinceCode STRING, CountryRegionCode STRING,
        IsOnlyStateProvinceFlag INT, Name STRING, TerritoryID INT,
        rowguid STRING, ModifiedDate STRING""",

    "Product": """ProductID INT, Name STRING, ProductNumber STRING, MakeFlag INT,
        FinishedGoodsFlag INT, Color STRING, SafetyStockLevel INT, ReorderPoint INT,
        StandardCost DOUBLE, ListPrice DOUBLE, Size STRING, SizeUnitMeasureCode STRING,
        WeightUnitMeasureCode STRING, Weight DOUBLE, DaysToManufacture DOUBLE,
        ProductLine STRING, Class STRING, Style STRING, ProductSubCategoryID STRING,
        ProductModelID STRING, SellStartDate STRING, SellEndDate STRING,
        DiscontinuedDate STRING, rowguid STRING, ModifiedDate STRING""",

    "productCategory": """ProductCategoryID INT, Name STRING, rowguid STRING, ModifiedDate STRING""",

    "productSubCategory": """ProductSubCategoryID INT, ProductCategoryID INT, Name STRING,
        rowguid STRING, ModifiedDate STRING""",

    "SalesOrderHeader": """SalesOrderID INT, RevisionNumber INT, OrderDate STRING, DueDate STRING,
        ShipDate STRING, Status INT, OnlineOrderFlag INT, SalesOrderNumber STRING,
        PurchaseOrderNumber STRING, AccountNumber STRING, CustomerID INT,
        SalesPersonID DOUBLE, TerritoryID INT, BillToAddressID INT, ShipToAddressID INT,
        ShipMethodID INT, CreditCardID DOUBLE, CreditCardApprovalCode STRING,
        CurrencyRateID DOUBLE, SubTotal DOUBLE, TaxAmt DOUBLE, Freight DOUBLE,
        TotalDue DOUBLE, Comment STRING, rowguid STRING, ModifiedDate STRING""",
}

# Diese CSV-Dateien haben eine Kopfzeile
files_with_header = ["productCategory", "productSubCategory"]



## CSV Rohdaten einlesen

Wir erstellen ein Wörterbuch für die Rohdaten, wobei der Schlüssel der Tabellenname (in Kleinbuchstaben) ist und der Wert ein Tupel ist, das zwei Dinge enthält: 
1) den aus der CSV-Datei gelesenen DataFrame, 
2) den Pfad zu dieser Datei.

In [0]:

# DBTITLE 1,Step 3: Rohdaten einlesen (CSV)

# Hier sammeln wir alle DataFrames: Tabellenname -> (DataFrame, Dateipfad)
raw_dataframes = {}

for name in csv_schemas:

    file_path = paths["raw"] + name + ".csv"

    if name in files_with_header:
        header_option = "true"
    else:
        header_option = "false"

    df = (
        spark.read
        .format("csv")
        .option("header", header_option)
        .schema(csv_schemas[name])
        .load(file_path)
    )

    raw_dataframes[name.lower()] = (df, file_path)
    

## Rohdaten einlesen (JSON, flatten)

Struktur von JSON-Dateien:
Unsere JSON-Dateien sind mehrzeilig(multiline).
Äußere Liste: Die gesamte Datei ist eine Liste.
Jedes Element der Liste: Ein dictionary, das eine Tabellenzeile repräsentiert.
Innerhalb jedes dict: Einfache Wertschlüssel (z. B. salesOrderId und modifiedDate) und zwei Schlüssel, deren Werte selbst dict sind: product und orderLine.
In verschachtelten dict: Wiederum Schlüssel-Wert-Paare (z. B. productId und unitPrice).

Ziel ist es, die verschachtelte JSON-Struktur zu flatten, um wieder die flache Haupttabelle (z. B. SalesOrderDetail) zu erhalten.


In [0]:
# DBTITLE 1,Step 3: Rohdaten einlesen (JSON, flatten)

# Customer.json
customer_path = paths["raw"] + "Customer.json"

df_customer_raw = spark.read.option("multiLine", "true").json(customer_path)

df_customer = df_customer_raw.select(
    F.col("customer.accountNumber").alias("customer_accountNumber"),
    F.col("customer.customerId").alias("customerId"),
    F.col("customer.modifiedDate").alias("modifiedDate"),
    F.col("customer.rowGuid").alias("rowGuid"),
    F.col("customer_details.accountNumber").alias("details_accountNumber"),
    F.col("customer_details.personId").alias("personId"),
    F.col("customer_details.territoryId").alias("territoryId"),
)

raw_dataframes["customer"] = (df_customer, customer_path)


# SalesOrderDetail.json
order_detail_path = paths["raw"] + "SalesOrderDetail.json"

df_order_detail_raw = spark.read.option("multiLine", "true").json(order_detail_path)

df_order_detail = df_order_detail_raw.select(
    F.col("salesOrderId"),
    F.col("specialOfferId"),
    F.col("carrierTrackingNumber"),
    F.col("modifiedDate"),
    F.col("rowGuid"),
    F.col("orderLine.salesOrderDetailId").alias("salesOrderDetailId"),
    F.col("orderLine.orderQty").alias("orderQty"),
    F.col("orderLine.lineTotal").alias("lineTotal"),
    F.col("product.productId").alias("productId"),
    F.col("product.unitPrice").alias("unitPrice"),
    F.col("product.unitPriceDiscount").alias("unitPriceDiscount"),
)

raw_dataframes["salesorderdetail"] = (df_order_detail, order_detail_path)

### Append-Logik
Beim erstmaligen Erstellen werden alle Daten in die Tabellen geschrieben.
Sind die Daten bereits in der standardized-Schicht vorhanden, werden nur neue oder
geänderte Zeilen angehängt (Zeilen, die dort noch nicht exakt so existieren).
Zusätzlich werden die Spalten `ingest_timestamp` und `source_file` ergänzt.

In [0]:
# DBTITLE 1,Step 3: Append-Logik (nur neue/geänderte Zeilen)

for table_name in raw_dataframes:

    df_raw = raw_dataframes[table_name][0]
    file_path = raw_dataframes[table_name][1]
    target_path = paths["standardized"] + table_name

    # Existiert die Delta-Tabelle schon?
    table_exists = DeltaTable.isDeltaTable(spark, target_path)

    if table_exists:
        # Bestehende Daten (ohne Metadaten-Spalten) laden
        df_existing = (
            spark.read
            .format("delta")
            .load(target_path)
            .select(df_raw.columns)
        )
        # Nur Zeilen behalten, die es in der Tabelle noch nicht gibt
        df_new = df_raw.subtract(df_existing)
    else:
        # Erster Lauf: alle Zeilen
        df_new = df_raw

    # Metadaten-Spalten hinzufügen
    df_new = (
        df_new
        .withColumn("ingest_timestamp", F.current_timestamp())
        .withColumn("source_file", F.lit(file_path))
    )

    n_new = df_new.count()

    if n_new > 0:
        df_new.write.format("delta").mode("append").save(target_path)

    print(table_name, "->", n_new, "Zeilen angehängt")



person -> 0 Zeilen angehängt
address -> 0 Zeilen angehängt
countryregion -> 0 Zeilen angehängt
stateprovince -> 0 Zeilen angehängt
product -> 2 Zeilen angehängt
productcategory -> 0 Zeilen angehängt
productsubcategory -> 0 Zeilen angehängt
salesorderheader -> 0 Zeilen angehängt


## Validierung
Zuerst ersetzen wir in raw die Datei Product.csv durch ProductUpdated.csv (umbenannt in Product.csv). Danach führen wir die Zellen zum Einlesen der Rohdaten und die Append-Logik erneut aus. In dieser Zelle prüfen wir das Ergebnis: wir vergleichen die Zeilenanzahl vor und nach dem Update (mit Time Travel über versionAsOf), filtere nach den ProductIDs 1000 und 1001 .Am Ende sind zwei neue Zeilen in der standardized-Schicht vorhanden, und die alten Datensätze bleiben erhalten.


In [0]:
# DBTITLE 1,Step 3: Validierung - aktueller Stand

for table_name in raw_dataframes:
    n = spark.read.format("delta").load(paths["standardized"] + table_name).count()
    print(table_name, "->", n, "rows")

# DBTITLE 1,Step 3: Product vor und nach dem Update

product_path = paths["standardized"] + "product"

df_product = spark.read.format("delta").load(product_path)

count_after = df_product.count()
count_before = (
    spark.read.format("delta")
    .option("versionAsOf", 0)
    .load(product_path)
    .count()
)

print("Product rows vorher:", count_before, "| nachher:", count_after)
print("Neue Zeilen:", count_after - count_before)

# Die beiden neuen Datensätze
display(df_product.filter(F.col("ProductID").isin(1000, 1001)))

# Alte und neue Zeilen nach Ladezeitpunkt
display(
    df_product
    .groupBy("ingest_timestamp", "source_file")
    .count()
    .orderBy("ingest_timestamp")
)


person -> 19972 rows
address -> 19614 rows
countryregion -> 238 rows
stateprovince -> 181 rows
product -> 506 rows
productcategory -> 4 rows
productsubcategory -> 37 rows
salesorderheader -> 31465 rows
Product rows vorher: 504 | nachher: 506
Neue Zeilen: 2


ProductID,Name,ProductNumber,MakeFlag,FinishedGoodsFlag,Color,SafetyStockLevel,ReorderPoint,StandardCost,ListPrice,Size,SizeUnitMeasureCode,WeightUnitMeasureCode,Weight,DaysToManufacture,ProductLine,Class,Style,ProductSubCategoryID,ProductModelID,SellStartDate,SellEndDate,DiscontinuedDate,rowguid,ModifiedDate,ingest_timestamp,source_file
1000,Adjustable Race 2025 Model,AR-5382,0,0,null,1000,750,150.5,200.5,null,null,null,null,0.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{694215B7-08F7-4C0D-ACB1-D734BA44C0C9},2025-11-04 00:00:00,2026-10-19T12:08:41.543531Z,/mnt/Mount_Point_fy/raw/Product.csv
1001,"Road-750 Golden, 52",BN-R43G-52,1,1,Golden,80,75,383.6496,539.99,52,CM,LB,20.42,4.0,R,L,U,2,31,2013-05-30 00:00:00,null,null,{AE638923-2B67-4679-B90E-ABBAB17DCA31},2025-11-00 00:00:00,2026-10-19T12:08:41.543531Z,/mnt/Mount_Point_fy/raw/Product.csv


ingest_timestamp,source_file,count
2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv,504
2026-10-19T12:08:41.543531Z,/mnt/Mount_Point_fy/raw/Product.csv,2


## Schritte 4: Bereinigung und Merge:

In [0]:
# DBTITLE 1,Step 4: Imports und Standardized-Tabellen einlesen

 
# Hinweis: In paths muss zusätzlich der Schlüssel "processed" existieren, z.B.
# paths["processed"] = base + "/processed/"
 
df_person = spark.read.format("delta").load(paths["standardized"] + "person")
df_address = spark.read.format("delta").load(paths["standardized"] + "address")
df_country = spark.read.format("delta").load(paths["standardized"] + "countryregion")
df_state = spark.read.format("delta").load(paths["standardized"] + "stateprovince")
df_product = spark.read.format("delta").load(paths["standardized"] + "product")
df_category = spark.read.format("delta").load(paths["standardized"] + "productcategory")
df_subcategory = spark.read.format("delta").load(paths["standardized"] + "productsubcategory")
df_header = spark.read.format("delta").load(paths["standardized"] + "salesorderheader")
df_customer = spark.read.format("delta").load(paths["standardized"] + "customer")
df_detail = spark.read.format("delta").load(paths["standardized"] + "salesorderdetail")
 

In [0]:

# DBTITLE 1,Step 4: Person bereinigen
display(df_person)
# ModifiedDate enthält am Ende das unerwünschte Suffix '&|' -> entfernen
# AdditionalContactInfo ist für die Auswertung nicht relevant
df_fixed_person = (
    df_person
    .withColumn("ModifiedDate", F.regexp_replace(col("ModifiedDate"), r"&\|", ""))
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
)

BusinessEntityID,PersonType,NameStyle,Title,FirstName,MiddleName,LastName,Suffix,EmailPromotion,AdditionalContactInfo,ModifiedDate,ingest_timestamp,source_file
1,EM,0,null,Ken,J,Sánchez,null,0,null,2009-01-07 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
2,EM,0,null,Terri,Lee,Duffy,null,1,null,2008-01-24 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
3,EM,0,null,Roberto,null,Tamburello,null,0,null,2007-11-04 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
4,EM,0,null,Rob,null,Walters,null,0,null,2007-11-28 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
5,EM,0,Ms.,Gail,A,Erickson,null,0,null,2007-12-30 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
6,EM,0,Mr.,Jossef,H,Goldberg,null,0,null,2013-12-16 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
7,EM,0,null,Dylan,A,Miller,null,2,null,2009-02-01 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
8,EM,0,null,Diane,L,Margheim,null,0,null,2008-12-22 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
9,EM,0,null,Gigi,N,Matthew,null,0,null,2009-01-09 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv
10,EM,0,null,Michael,null,Raheem,null,2,null,2009-04-26 00:00:00&|,2026-10-19T12:00:16.414809Z,/mnt/Mount_Point_fy/raw/Person.csv


In [0]:
 
# DBTITLE 1,Step 4: Address, CountryRegion, StateProvince bereinigen
display(df_address)
display(df_country)
display(df_state) 
# SpatialLocation und rowguid sind für die Auswertung nicht relevant
df_fixed_address = (
    df_address
    .drop("SpatialLocation", "rowguid")
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
)

# _c3 ist eine leere Hilfsspalte aus dem Einlesen der CSV
df_fixed_country = (
    df_country
    .drop("_c3")
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
)
 
df_fixed_state = (
    df_state
    .drop("rowguid")
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
)
 

AddressID,AddressLine1,AddressLine2,City,StateProvinceID,PostalCode,SpatialLocation,rowguid,ModifiedDate,ingest_timestamp,source_file
1,1970 Napa Ct.,null,Bothell,79,98011,E6100000010CAE8BFC28BCE4474067A89189898A5EC0,{9AADCB0D-36CF-483F-84D8-585C2D4EC6E9},2007-12-04 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
2,9833 Mt. Dias Blv.,null,Bothell,79,98011,E6100000010CD6FA851AE6D74740BC262A0A03905EC0,{32A54B9E-E034-4BFB-B573-A71CDE60D8C0},2008-11-30 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
3,7484 Roundtree Drive,null,Bothell,79,98011,E6100000010C18E304C4ADE14740DA930C7893915EC0,{4C506923-6D1B-452C-A07C-BAA6F5B142A4},2013-03-07 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
4,9539 Glenside Dr,null,Bothell,79,98011,E6100000010C813A0D5F9FDE474011A5C28A7C955EC0,{E5946C78-4BCC-477F-9FA1-CC09DE16A880},2009-02-03 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
5,1226 Shoe St.,null,Bothell,79,98011,E6100000010C61C64D8ABBD94740C460EA3FD8855EC0,{FBAFF937-4A97-4AF0-81FD-B849900E9BB0},2008-12-19 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
6,1399 Firestone Drive,null,Bothell,79,98011,E6100000010CE0B4E50458DA47402F12A5F80C975EC0,{FEBF8191-9804-44C8-877A-33FDE94F0075},2009-02-13 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
7,5672 Hale Dr.,null,Bothell,79,98011,E6100000010C18E304C4ADE1474011A5C28A7C955EC0,{0175A174-6C34-4D41-B3C1-4419CD6A0446},2009-12-11 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
8,6387 Scenic Avenue,null,Bothell,79,98011,E6100000010C0029A5D93BDF4740E248962FD5975EC0,{3715E813-4DCA-49E0-8F1C-31857D21F269},2008-12-17 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
9,8713 Yosemite Ct.,null,Bothell,79,98011,E6100000010C6A80AD742DDC4740851574F7198C5EC0,{268AF621-76D7-4C78-9441-144FD139821A},2012-05-30 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv
10,250 Race Court,null,Bothell,79,98011,E6100000010C219D64AE1FE4474040862564B7825EC0,{0B6B739D-8EB6-4378-8D55-FE196AF34C04},2008-12-02 00:00:00,2026-10-19T12:00:22.236468Z,/mnt/Mount_Point_fy/raw/Address.csv


CountryRegionCode,Name,ModifiedDate,_c3,ingest_timestamp,source_file
AD,Andorra,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AE,United Arab Emirates,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AF,Afghanistan,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AG,Antigua and Barbuda,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AI,Anguilla,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AL,Albania,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AM,Armenia,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AN,Netherlands Antilles,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AO,Angola,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv
AQ,Antarctica,2008-04-30 00:00:00,null,2026-10-19T12:00:26.653788Z,/mnt/Mount_Point_fy/raw/CountryRegion.csv


StateProvinceID,StateProvinceCode,CountryRegionCode,IsOnlyStateProvinceFlag,Name,TerritoryID,rowguid,ModifiedDate,ingest_timestamp,source_file
1,AB,CA,0,Alberta,6,298C2880-AB1C-4982-A5AD-A36EB4BA0D34,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
2,AK,US,0,Alaska,1,5B7B8462-A888-4E0B-A3E1-7278F8AF107E,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
3,AL,US,0,Alabama,5,41B328BE-21AE-45D0-841D-6F8DD71CE626,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
4,AR,US,0,Arkansas,3,54656A80-06F2-4C70-BA10-247179FC246E,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
5,AS,AS,1,American Samoa,1,255D15E1-9F6E-4CF8-9E5F-6B3858AD9B6A,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
6,AZ,US,0,Arizona,4,FB8BE18E-F441-44F0-A4A9-1D0F204CB701,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
7,BC,CA,0,British Columbia,6,D27FCC6E-BB99-438B-BA86-285CEEB2FA53,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
8,BY,DE,0,Bayern,8,D54E5000-A0DA-46D1-86B0-B8FE16C9F781,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
9,CA,US,0,California,4,3B2FF23C-1C75-40AE-9093-F4EB42263F4E,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv
10,CO,US,0,Colorado,3,292DF595-7D3C-41FB-A040-7C184D379FCE,2014-02-08 10:17:21.587000000,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv


In [0]:

# DBTITLE 1,Step 4: Product, ProductCategory, ProductSubCategory bereinigen
display(df_product)
display(df_category)
display(df_subcategory) 
columns_to_drop = ("MakeFlag", "FinishedGoodsFlag", "DaysToManufacture", "rowguid")
 
df_fixed_product = (
    df_product
    .drop(*columns_to_drop)
 
    # String wie "14.0" -> erst double, dann integer
    .withColumn("ProductSubCategoryID", col("ProductSubCategoryID").cast("double").cast("integer"))
    .withColumn("ProductModelID", col("ProductModelID").cast("double").cast("integer"))
 
    # Datumsfelder von String zu Timestamp
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
    .withColumn("SellStartDate", try_to_timestamp(col("SellStartDate")))
    .withColumn("SellEndDate", try_to_timestamp(col("SellEndDate")))
    .withColumn("DiscontinuedDate", try_to_timestamp(col("DiscontinuedDate")))
)
 
df_fixed_category = (
    df_category
    .drop("rowguid")
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
)
 
df_fixed_subcategory = (
    df_subcategory
    .drop("rowguid")
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
)
 

ProductID,Name,ProductNumber,MakeFlag,FinishedGoodsFlag,Color,SafetyStockLevel,ReorderPoint,StandardCost,ListPrice,Size,SizeUnitMeasureCode,WeightUnitMeasureCode,Weight,DaysToManufacture,ProductLine,Class,Style,ProductSubCategoryID,ProductModelID,SellStartDate,SellEndDate,DiscontinuedDate,rowguid,ModifiedDate,ingest_timestamp,source_file
1,Adjustable Race,AR-5381,0,0,null,1000,750,0.0,0.0,null,null,null,null,0.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{694215B7-08F7-4C0D-ACB1-D734BA44C0C8},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
2,Bearing Ball,BA-8327,0,0,null,1000,750,0.0,0.0,null,null,null,null,0.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{58AE3C20-4F3A-4749-A7D4-D568806CC537},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
3,BB Ball Bearing,BE-2349,1,0,null,800,600,0.0,0.0,null,null,null,null,1.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{9C21AED2-5BFA-4F18-BCB8-F11638DC2E4E},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
4,Headset Ball Bearings,BE-2908,0,0,null,800,600,0.0,0.0,null,null,null,null,0.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{ECFED6CB-51FF-49B5-B06C-7D8AC834DB8B},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
316,Blade,BL-2036,1,0,null,800,600,0.0,0.0,null,null,null,null,1.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{E73E9750-603B-4131-89F5-3DD15ED5FF80},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
317,LL Crankarm,CA-5965,0,0,Black,500,375,0.0,0.0,null,null,null,null,0.0,null,L,null,null,null,2008-04-30 00:00:00,null,null,{3C9D10B7-A6B2-4774-9963-C19DCEE72FEA},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
318,ML Crankarm,CA-6738,0,0,Black,500,375,0.0,0.0,null,null,null,null,0.0,null,M,null,null,null,2008-04-30 00:00:00,null,null,{EABB9A92-FA07-4EAB-8955-F0517B4A4CA7},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
319,HL Crankarm,CA-7457,0,0,Black,500,375,0.0,0.0,null,null,null,null,0.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{7D3FD384-4F29-484B-86FA-4206E276FE58},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
320,Chainring Bolts,CB-2903,0,0,Silver,1000,750,0.0,0.0,null,null,null,null,0.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{7BE38E48-B7D6-4486-888E-F53C26735101},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv
321,Chainring Nut,CN-6137,0,0,Silver,1000,750,0.0,0.0,null,null,null,null,0.0,null,null,null,null,null,2008-04-30 00:00:00,null,null,{3314B1D7-EF69-4431-B6DD-DC75268BD5DF},2014-02-08 10:01:36.827000000,2026-10-19T12:00:33.91959Z,/mnt/Mount_Point_fy/raw/Product.csv


ProductCategoryID,Name,rowguid,ModifiedDate,ingest_timestamp,source_file
1,Bikes,{CFBDA25C-DF71-47A7-B81B-64EE161AA37C},2008-04-30 00:00:00,2026-10-19T12:00:37.553171Z,/mnt/Mount_Point_fy/raw/productCategory.csv
2,Components,{C657828D-D808-4ABA-91A3-AF2CE02300E9},2008-04-30 00:00:00,2026-10-19T12:00:37.553171Z,/mnt/Mount_Point_fy/raw/productCategory.csv
3,Clothing,{10A7C342-CA82-48D4-8A38-46A2EB089B74},2008-04-30 00:00:00,2026-10-19T12:00:37.553171Z,/mnt/Mount_Point_fy/raw/productCategory.csv
4,Accessories,{2BE3BE36-D9A2-4EEE-B593-ED895D97C2A6},2008-04-30 00:00:00,2026-10-19T12:00:37.553171Z,/mnt/Mount_Point_fy/raw/productCategory.csv


ProductSubCategoryID,ProductCategoryID,Name,rowguid,ModifiedDate,ingest_timestamp,source_file
1,1,Mountain Bikes,{2D364ADE-264A-433C-B092-4FCBF3804E01},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
2,1,Road Bikes,{000310C0-BCC8-42C4-B0C3-45AE611AF06B},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
3,1,Touring Bikes,{02C5061D-ECDC-4274-B5F1-E91D76BC3F37},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
4,2,Handlebars,{3EF2C725-7135-4C85-9AE6-AE9A3BDD9283},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
5,2,Bottom Brackets,{A9E54089-8A1E-4CF5-8646-E3801F685934},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
6,2,Brakes,{D43BA4A3-EF0D-426B-90EB-4BE4547DD30C},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
7,2,Chains,{E93A7231-F16C-4B0F-8C41-C73FDEC62DA0},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
8,2,Cranksets,{4F644521-422B-4F19-974A-E3DF6102567E},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
9,2,Derailleurs,{1830D70C-AA2A-40C0-A271-5BA86F38F8BF},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv
10,2,Forks,{B5F9BA42-B69B-4FDD-B2EC-57FB7B42E3CF},2008-04-30 00:00:00,2026-10-19T12:00:40.816834Z,/mnt/Mount_Point_fy/raw/productSubCategory.csv


In [0]:
 
# DBTITLE 1,Step 4: SalesOrderHeader bereinigen
# Status-Codes (laut AdventureWorks Data Dictionary) in Text umwandeln
df_fixed_header = (
    df_header
    .drop("rowguid", "Comment")
    .withColumn(
        "Status",
        F.when(col("Status") == 1, "In process")
         .when(col("Status") == 2, "Approved")
         .when(col("Status") == 3, "Backordered")
         .when(col("Status") == 4, "Rejected")
         .when(col("Status") == 5, "Shipped")
         .when(col("Status") == 6, "Cancelled")
         .otherwise("Unknown")
    )
    .withColumn("OrderDate", try_to_timestamp(col("OrderDate")))
    .withColumn("DueDate", try_to_timestamp(col("DueDate")))
    .withColumn("ShipDate", try_to_timestamp(col("ShipDate")))
    .withColumn("ModifiedDate", try_to_timestamp(col("ModifiedDate")))
    .withColumn("SalesPersonID", col("SalesPersonID").cast("integer"))
    .withColumn("CreditCardID", col("CreditCardID").cast("integer"))
    .withColumn("CurrencyRateID", col("CurrencyRateID").cast("integer"))
)
 

In [0]:

# DBTITLE 1,Step 4: Customer bereinigen
 
# Das JSON wurde schon in Step 3 geflattet.
# "AW" am Anfang der Kontonummer durch "CustNo" ersetzen
df_fixed_customer = (
    df_customer
    .drop("rowguid")
    .withColumn("customer_accountNumber", F.regexp_replace(col("customer_accountNumber"), "AW", "CustNo"))
    .withColumn("details_accountNumber", F.regexp_replace(col("details_accountNumber"), "AW", "CustNo"))
    .withColumn("modifiedDate", try_to_timestamp(col("modifiedDate")))
)

In [0]:
df_fixed_detail = (
    df_detail
    .drop("rowGuid")

    # Negative Preise korrigieren (Betrag nehmen)
    .withColumn("unitPrice", F.abs(col("unitPrice")))

    # Fehlende orderQty (NULL oder NaN) aus lineTotal / (unitPrice * (1 - Rabatt)) berechnen
    .withColumn(
        "orderQty",
        F.when(
            (col("orderQty").isNull() | F.isnan(col("orderQty")))
            & (col("unitPrice") * (1 - col("unitPriceDiscount")) > 0),
            F.round(F.abs(col("lineTotal")) / (col("unitPrice") * (1 - col("unitPriceDiscount"))))
        ).otherwise(col("orderQty"))
    )

    # try_cast: nicht umrechenbare Werte werden NULL statt Fehler
    .withColumn("orderQty", F.expr("try_cast(orderQty as int)"))

    # Datentyp
    .withColumn("modifiedDate", try_to_timestamp(col("modifiedDate")))
)

# Kontrolle: gibt es noch fehlende orderQty oder negative Preise?
print("orderQty NULL:", df_fixed_detail.filter(col("orderQty").isNull() | F.isnan(col("orderQty"))).count())
print("unitPrice < 0:", df_fixed_detail.filter(col("unitPrice") < 0).count())

orderQty NULL: 0
unitPrice < 0: 0


## Inkrementell Logik

In [0]:

# DBTITLE 1,Step 4: Tabellen und Merge-Schlüssel festlegen
 
# Tabellenname -> (bereinigter DataFrame, Merge-Schlüssel)
processed_tables = {
    "person":             (df_fixed_person, ["BusinessEntityID"]),
    "address":            (df_fixed_address, ["AddressID"]),
    "countryregion":      (df_fixed_country, ["CountryRegionCode"]),
    "stateprovince":      (df_fixed_state, ["StateProvinceID"]),
    "product":            (df_fixed_product, ["ProductID"]),
    "productcategory":    (df_fixed_category, ["ProductCategoryID"]),
    "productsubcategory": (df_fixed_subcategory, ["ProductSubCategoryID"]),
    "salesorderheader":   (df_fixed_header, ["SalesOrderID"]),
    "customer":           (df_fixed_customer, ["customerId"]),
    "salesorderdetail":   (df_fixed_detail, ["salesOrderId", "salesOrderDetailId"]),
}

In [0]:
 
# DBTITLE 1,Step 4: Inkrementell nach processed schreiben (Merge)
 
for table_name in processed_tables:
 
    df_clean = processed_tables[table_name][0]
    key_columns = processed_tables[table_name][1]
    deltaPath = paths["processed"] + table_name
 
    # standardized enthält mehrere Versionen pro Datensatz (Append-Historie).
    # Für processed behalten wir nur die neueste Version pro Schlüssel.
    window_spec = (
        Window
        .partitionBy(*key_columns)
        .orderBy(col("ModifiedDate").desc(), col("ingest_timestamp").desc())
    )
 
    df_latest = (
        df_clean
        .withColumn("rn", F.row_number().over(window_spec))
        .filter(col("rn") == 1)
        .drop("rn")
    )
 
    if not DeltaTable.isDeltaTable(spark, deltaPath):
 
        # ERSTER LAUF: Tabelle komplett schreiben
        df_latest.write.format("delta").mode("overwrite").save(deltaPath)
        print(table_name, "-> erster Lauf, Tabelle erstellt")
 
    else:
 
        # FOLGE-LÄUFE: per MERGE aktualisieren
        # Merge-Bedingung aus den Schlüsselspalten zusammensetzen
        merge_condition = ""
        for k in key_columns:
            if merge_condition != "":
                merge_condition = merge_condition + " AND "
            merge_condition = merge_condition + "t." + k + " = s." + k
 
        delta_tbl = DeltaTable.forPath(spark, deltaPath)
 
        (
            delta_tbl
            .alias("t")
            .merge(df_latest.alias("s"), merge_condition)
            # Nur aktualisieren, wenn ModifiedDate neuer ist
            .whenMatchedUpdateAll(condition="s.ModifiedDate > t.ModifiedDate")
            # Neue Schlüssel einfügen
            .whenNotMatchedInsertAll()
            .execute()
        )
        print(table_name, "-> Merge ausgeführt")

person -> erster Lauf, Tabelle erstellt
address -> erster Lauf, Tabelle erstellt
countryregion -> erster Lauf, Tabelle erstellt
stateprovince -> erster Lauf, Tabelle erstellt
product -> erster Lauf, Tabelle erstellt
productcategory -> erster Lauf, Tabelle erstellt
productsubcategory -> erster Lauf, Tabelle erstellt
salesorderheader -> erster Lauf, Tabelle erstellt
customer -> erster Lauf, Tabelle erstellt
salesorderdetail -> erster Lauf, Tabelle erstellt


In [0]:
 
# DBTITLE 1,Step 4 Validierung: 1) Zeilen mit "Seine (Paris)" anzeigen
 
df_state_std = spark.read.format("delta").load(paths["standardized"] + "stateprovince")
 
df_seine = df_state_std.filter(col("Name") == "Seine (Paris)")
 
display(df_seine)
print("Anzahl Zeilen:", df_seine.count())

StateProvinceID,StateProvinceCode,CountryRegionCode,IsOnlyStateProvinceFlag,Name,TerritoryID,rowguid,ModifiedDate,ingest_timestamp,source_file
161,75,FR,0,Seine (Paris),7,E117A6FC-24B9-438B-86FF-8455107F4E9F,2008-04-30 00:00:00,2026-10-19T12:00:30.435194Z,/mnt/Mount_Point_fy/raw/StateProvince.csv


Anzahl Zeilen: 1


In [0]:

# DBTITLE 1,Step 4 Validierung: 2) Zeilen aktualisieren (neue Version anhängen)
 
# standardized ist append-only: die geänderte Zeile wird als neue Version angehängt
df_seine_updated = (
    df_seine
    .withColumn("Name", F.lit("Paris"))
    .withColumn("StateProvinceCode", F.lit("FR-PAR"))
    .withColumn("ModifiedDate", F.current_timestamp().cast("string"))
    .withColumn("ingest_timestamp", F.current_timestamp())
)
 
df_seine_updated.write.format("delta").mode("append").save(paths["standardized"] + "stateprovince")
display(df_seine_updated)
 

StateProvinceID,StateProvinceCode,CountryRegionCode,IsOnlyStateProvinceFlag,Name,TerritoryID,rowguid,ModifiedDate,ingest_timestamp,source_file
161,FR-PAR,FR,0,Paris,7,E117A6FC-24B9-438B-86FF-8455107F4E9F,2026-10-19 12:12:12.368512,2026-10-19T12:12:12.368512Z,/mnt/Mount_Point_fy/raw/StateProvince.csv


In [0]:

# DBTITLE 1,Step 4 Validierung: 3) Zellen "Standardized-Tabellen einlesen", "StateProvince" und "Merge" erneut ausführen
 
 
# DBTITLE 1,Step 4 Validierung: 4) processed/stateprovince prüfen
 
df_state_processed = spark.read.format("delta").load(paths["processed"] + "stateprovince")
 
display(df_state_processed.filter(col("Name") == "Paris"))
 
# Es darf keine Zeile "Seine (Paris)" mehr geben, die StateProvinceID bleibt gleich
print("Seine (Paris):", df_state_processed.filter(col("Name") == "Seine (Paris)").count())
 

StateProvinceID,StateProvinceCode,CountryRegionCode,IsOnlyStateProvinceFlag,Name,TerritoryID,ModifiedDate,ingest_timestamp,source_file


Seine (Paris): 1
